In [94]:
import os
import re
import pandas as pd
import numpy as np
import matplotlib.pyplot as plt

from pycatch22 import catch22_all 
from joblib import Parallel, delayed 
import pandas as pd

import itertools
from pathlib import Path
import plotly.express as px
import plotly.graph_objects as go


from sklearn.preprocessing import StandardScaler
from sklearn.metrics import pairwise_distances
from sklearn.covariance import LedoitWolf  
from scipy.spatial.distance import cdist
from sklearn.preprocessing import LabelEncoder
from sklearn.ensemble import RandomForestClassifier
from sklearn.multioutput import MultiOutputClassifier
from sklearn.model_selection import GridSearchCV





In [95]:
# ================================================================
# binlite -> aplicar operación "acre_rate_mass_weighted" EXACTA -> gráfico interactivo
# ================================================================

# --- Dependencias (instala si faltan) ---
import sys, subprocess
def _ensure(pkg: str):
    try:
        __import__(pkg)
    except ImportError:
        subprocess.check_call([sys.executable, "-m", "pip", "install", pkg])

for _pkg in ("numpy", "pandas", "plotly", "binlite"):
    _ensure(_pkg)

# --- Imports ---
from pathlib import Path
import re
import numpy as np
import pandas as pd
import plotly.graph_objects as go
import plotly.io as pio
from typing import Optional

# Render interactivo en Jupyter
try:
    pio.renderers.default = "notebook_connected"
except Exception:
    pass

# ----------------------- Generación con binlite -----------------------
def generar_binlite_df(
    *,
    q: float = 1.0,          # usado para el PESO w1,w2 y para etiquetar (binlite físico es q=1)
    e: float = 0.30,         # excentricidad
    n_orbits: int = 10,
    n_modes: int = 29,
    retrograde: bool = False,
) -> pd.DataFrame:
    """
    Devuelve DataFrame con columnas:
      time, acre_rate_primary, acre_rate_secondary
    """
    import binlite as blt
    acc = blt.AccretionSeries(
        eccentricity=float(e),
        n_orbits=int(n_orbits),
        n_modes=int(n_modes),
        retrograde=bool(retrograde),
    )

    # t en órbitas
    t = np.asarray(getattr(acc, "time"), dtype=float)

    # mdot por componente (binlite: primario/secundario). Tus archivos los llevan negativos,
    # pero tu operación usa ABS(), así que el signo no afecta.
    if hasattr(acc, "primary") and hasattr(acc, "secondary"):
        mdot_primary   = np.asarray(acc.primary, dtype=float)
        mdot_secondary = np.asarray(acc.secondary, dtype=float)
    else:
        # Fallback raro: si no están, dividimos el total 50/50 (q=1 de binlite)
        tot = np.asarray(acc.total, dtype=float)
        mdot_primary   = 0.5 * tot
        mdot_secondary = 0.5 * tot

    df = pd.DataFrame({
        "time": t,
        "acre_rate_primary":   mdot_primary,     # podrían ser >0; tus archivos los guardaban negativos
        "acre_rate_secondary": mdot_secondary,
    })
    # Metadatos útiles
    df["q"] = float(q)
    df["e"] = float(e)
    # ID estilo "q100_e030" (por ejemplo). No incluimos segmento aquí.
    q_tag = f"{int(round(q*100)):03d}"
    e_tag = f"{int(round(e*100)):03d}"
    df["id"] = f"{q_tag}_{e_tag}"
    return df

# ------------------- Tu operación EXACTA (weights + abs) -------------------
def agregar_mass_weighted(df: pd.DataFrame) -> pd.DataFrame:
    """
    Aplica EXACTAMENTE:
      w1 = 1/(1+q), w2 = q/(1+q)
      acre_rate_mass_weighted = w1*|primary| + w2*|secondary|
    usando q de la columna 'q' (constante en el df).
    """
    if "q" not in df.columns:
        raise ValueError("El DataFrame no tiene columna 'q'.")
    q_val = float(df["q"].iloc[0])
    w1 = 1.0 / (1.0 + q_val)
    w2 = q_val / (1.0 + q_val)
    df = df.copy()
    df["acre_rate_mass_weighted"] = (
        w1 * df["acre_rate_primary"].abs() + w2 * df["acre_rate_secondary"].abs()
    )
    return df

# -------------------------- Guardado opcional --------------------------
def guardar_csv(df: pd.DataFrame, ruta: Optional[str | Path] = None) -> Optional[Path]:
    if ruta is None:
        return None
    ruta = Path(ruta)
    ruta.parent.mkdir(parents=True, exist_ok=True)
    df.to_csv(ruta, index=False)
    return ruta

# --------------------- Gráfico interactivo (curva final) ---------------------
def plot_mass_weighted(df: pd.DataFrame, titulo: Optional[str] = None):
    if titulo is None:
        titulo = f"acre_rate_mass_weighted — q={df['q'].iloc[0]:.2f}, e={df['e'].iloc[0]:.2f}"
    fig = go.Figure()
    fig.add_scatter(x=df["time"], y=df["acre_rate_mass_weighted"],
                    mode="lines", name="acre_rate_mass_weighted")
    fig.update_layout(
        template="plotly_white",
        title=dict(text=titulo, x=0.5),
        xaxis_title="time [órbitas]",
        yaxis_title="acre_rate_mass_weighted (unid. modelo)",
        hovermode="x unified",
        height=420,
        margin=dict(l=60, r=20, t=60, b=40),
    )
    fig.update_xaxes(rangeslider=dict(visible=True))
    fig.show()

# =============================== USO RÁPIDO ===============================
# 1) Generar con binlite (q se usa como PESO y etiqueta; binlite físico es q=1)
# df = generar_binlite_df(q=1.00, e=0.30, n_orbits=10, n_modes=29, retrograde=False)
#
# 2) Aplicar tu operación EXACTA
# df = agregar_mass_weighted(df)
#
# 3) (Opcional) Guardar CSV con las columnas esperadas por tu pipeline
# csv_path = guardar_csv(df, "data/binlite_mass_weighted/q100_e030_mass_weighted.csv")
# print("CSV:", csv_path)
#
# 4) Graficar interactivamente SOLO la curva final (mass-weighted)
# plot_mass_weighted(df)


In [96]:
q=1.00
e=0.25

df = generar_binlite_df(q=q, e=e, n_orbits=200, n_modes=29, retrograde=False)
df = agregar_mass_weighted(df)
csv_path = guardar_csv(df, f"data/binlite_mass_weighted/q{q}_e{e}_mass_weighted.csv")
print("CSV:", csv_path)
plot_mass_weighted(df)


CSV: data/binlite_mass_weighted/q1.0_e0.25_mass_weighted.csv


In [97]:
df=pd.read_csv(csv_path)

In [98]:
df

,time,acre_rate_primary,acre_rate_secondary,q,e,id,acre_rate_mass_weighted
0,0.000000,0.201837,0.812083,1.0,0.25,100_025,0.506960
1,0.001001,0.203137,0.810578,1.0,0.25,100_025,0.506858
2,0.002002,0.204438,0.809061,1.0,0.25,100_025,0.506749
3,0.003003,0.205739,0.807529,1.0,0.25,100_025,0.506634
4,0.004004,0.207041,0.805984,1.0,0.25,100_025,0.506513
...,...,...,...,...,...,...,...
199995,199.995996,0.196654,0.817987,1.0,0.25,100_025,0.507320
199996,199.996997,0.197947,0.816525,1.0,0.25,100_025,0.507236
199997,199.997998,0.199242,0.815054,1.0,0.25,100_025,0.507148
199998,199.998999,0.200538,0.813574,1.0,0.25,100_025,0.507056


In [99]:
COL_MW      = "acre_rate_mass_weighted"
STD_FACTOR       =  0.4 #  20% de σ
RANDOM_SEED: int | None = None  # «None» → ruido distinto en cada ejecución

rng = np.random.default_rng(RANDOM_SEED) if RANDOM_SEED is not None else np.random.default_rng()
noisy_df = df.copy()

sigma = noisy_df[COL_MW].mean()

# Guarda copia limpia y sobre‑escribe la columna con su versión ruidosa
noisy_df[f"{COL_MW}_clean"] = noisy_df[COL_MW]
noise = rng.normal(0.0, STD_FACTOR * sigma, size=len(noisy_df))
noisy_df[COL_MW] = noisy_df[COL_MW] + noise

In [100]:
noisy_df

,time,acre_rate_primary,acre_rate_secondary,q,e,id,acre_rate_mass_weighted,acre_rate_mass_weighted_clean
0,0.000000,0.201837,0.812083,1.0,0.25,100_025,0.389186,0.506960
1,0.001001,0.203137,0.810578,1.0,0.25,100_025,0.401695,0.506858
2,0.002002,0.204438,0.809061,1.0,0.25,100_025,0.755467,0.506749
3,0.003003,0.205739,0.807529,1.0,0.25,100_025,0.443319,0.506634
4,0.004004,0.207041,0.805984,1.0,0.25,100_025,0.435532,0.506513
...,...,...,...,...,...,...,...,...
199995,199.995996,0.196654,0.817987,1.0,0.25,100_025,0.431452,0.507320
199996,199.996997,0.197947,0.816525,1.0,0.25,100_025,0.586098,0.507236
199997,199.997998,0.199242,0.815054,1.0,0.25,100_025,0.397385,0.507148
199998,199.998999,0.200538,0.813574,1.0,0.25,100_025,0.396335,0.507056


In [101]:
DAYS_PER_ORBIT = 270.0   #factor para ponderar orbita (30, 100,300)
OBS_FREQ_DAYS  = 28.0    #frecuencia observacion(1 = diario, 7 = semanal, 15 = quincenal)
# Claves que definen cada serie
clave = ['id']          # ajusta a tu caso
df['time_days'] = df['time'] * DAYS_PER_ORBIT

noisy_df['time_days'] = noisy_df['time'] * DAYS_PER_ORBIT
noisy_df['bucket'] = np.floor((noisy_df['time_days'] + 1e-9) / OBS_FREQ_DAYS).astype(int)

df_unique = (
    noisy_df
        .groupby(clave + ['bucket'], as_index=False)
        .median(numeric_only=True)
        .sort_values(clave + ['time_days'])
        #.drop(columns='bucket')
        .reset_index(drop=True)
)


In [102]:

def filtrar_por_ventana_meses(
    df: pd.DataFrame,
    *,
    col_dias: str = "time_days",
    mes_inicial: int = 1,
    n_meses: int = 6,
    dias_por_anio: int = 365,
    agregar_aux: bool = False
) -> pd.DataFrame:
    
    if col_dias not in df.columns:
        raise ValueError(f"La columna '{col_dias}' no existe en el DataFrame.")

    # Longitud real de cada mes (año no bisiesto)
    dias_mes = np.array([31, 28, 31, 30, 31, 30,
                         31, 31, 30, 31, 30, 31])
    limites = np.concatenate(([0], np.cumsum(dias_mes)))     # 0, 31, 59, …

    # Vector de días (int)
    dias_abs = df[col_dias].astype(int).to_numpy()

    # Año relativo y día dentro del año
    anio_rel = dias_abs // dias_por_anio
    dia_anio = dias_abs % dias_por_anio

    # Mes (1‒12) vía búsqueda binaria en los límites
    mes = np.searchsorted(limites, dia_anio, side="right")

    # Lista de meses permitidos
    meses_ok = [((mes_inicial - 1 + i) % 12) + 1 for i in range(n_meses)]

    # Máscara booleana final
    keep = np.isin(mes, meses_ok)

    out = df.loc[keep].copy().reset_index(drop=True)
    if agregar_aux:
        out["anio_rel"] = anio_rel[keep]
        out["mes"] = mes[keep]

    return out




In [103]:
ventana=9
df_estacion= filtrar_por_ventana_meses(df_unique,
                                       mes_inicial=0,
                                       n_meses=ventana,
                                       agregar_aux=True)

In [104]:
dfs = [df, noisy_df, df_unique, df_estacion]


In [105]:
import pandas as pd
from typing import List, Optional, Tuple, Union
import plotly.graph_objects as go
from plotly.subplots import make_subplots

def plot_id_across_dfs(
    dfs: List[pd.DataFrame],
    id: str,
    *,
    y: str = "acre_rate_mass_weighted",
    x_range: Optional[Tuple[Union[int, float], Union[int, float]]] = None,
    save_path: Optional[str] = None,
    height_per_plot: int = 300,
    # Nuevos parámetros de tamaño de fuente
    main_title_font_size: int = 20,
    subplot_title_font_size: int = 16,
    axis_title_font_size: int = 14,
    tick_font_size: int = 12
):
    """
    Dibuja el mismo segmento `id` en cada DataFrame de `dfs`,
    con control de tamaños de fuente.
    """
    n = len(dfs)
    titles = [
        "Original Simulations",
        f"Gaussian Noise | {STD_FACTOR*100}%",
        f"Observation Frecuency | Every {OBS_FREQ_DAYS} days",
        f"Seasonality | {ventana} months/year"
    ]

    fig = make_subplots(
        rows=n, cols=1,
        shared_xaxes=True,
        vertical_spacing=0.1,
        subplot_titles=titles
    )

    # Añade cada serie
    for row, df in enumerate(dfs, start=1):
        subset = df.loc[df["id"] == id].sort_values("time_days")
        fig.add_trace(
            go.Scatter(
                x=subset["time_days"],
                y=subset[y],
                mode="markers",
                marker=dict(size=4, color="black"),
                #marker=dict(size=4),
                showlegend=False
            ),
            row=row, col=1
        )
        # Tamaño de títulos de ejes
        fig.update_xaxes(
            title_text="time_days",
            title_font=dict(size=axis_title_font_size),
            tickfont=dict(size=tick_font_size),
            row=row, col=1
        )
        fig.update_yaxes(
            title_text=y,
            title_font=dict(size=axis_title_font_size),
            tickfont=dict(size=tick_font_size),
            row=row, col=1
        )

    # Rango de eje x opcional
    if x_range is not None:
        fig.update_xaxes(range=list(x_range))

    # Título principal y fuente por defecto (para texto de leyendas, si las hubiera)
    fig.update_layout(
        height=height_per_plot * n,
        template="plotly_white",
        title={
            "text": f"Evolution of data preparation for segment {id}",
            "x": 0.5,
            "font": {"size": main_title_font_size}
        },
        font={"size": tick_font_size}
    )

    # Ajustar tamaño de los subplot titles (son anotaciones internas)
    for ann in fig.layout.annotations:
        ann.font.size = subplot_title_font_size

    if save_path:
        fig.write_html(save_path)

    fig.show()


In [106]:
plot_id_across_dfs(
    dfs,
    id="100_025",
    main_title_font_size=26,
    subplot_title_font_size=22,
    axis_title_font_size=18,
    tick_font_size=12,
    x_range=(0, 50000)
)


In [107]:
def extract_catch22(id: str, grp: pd.DataFrame) -> pd.Series:
    values = grp.sort_values("time")["acre_rate_mass_weighted"].to_numpy()
    res = catch22_all(values)
    return pd.Series(res["values"], index=res["names"], name=id)


def compute_features(df: pd.DataFrame, n_jobs: int = -1) -> pd.DataFrame:

    grouped = df.groupby("id", sort=False)

    # Paralelización con joblib
    results = Parallel(n_jobs=n_jobs, verbose=1)(
        delayed(extract_catch22)(id, grp) for id, grp in grouped
    )

    features_df = pd.concat(results, axis=1).T
    features_df.reset_index(inplace=True)
    features_df.rename(columns={"index": "id"}, inplace=True)
    return features_df



In [108]:
all_data=pd.read_csv('n40_f28_p270_v9.csv')

In [109]:
df_unique

,id,bucket,time,acre_rate_primary,acre_rate_secondary,q,e,acre_rate_mass_weighted,acre_rate_mass_weighted_clean,time_days
0,100_025,0,0.051552,0.264613,0.735812,1.0,0.25,0.512012,0.500213,13.918919
1,100_025,1,0.155656,0.323154,0.577628,1.0,0.25,0.455637,0.451362,42.027027
2,100_025,2,0.259259,0.302054,0.430078,1.0,0.25,0.348608,0.366066,70.000000
3,100_025,3,0.362863,0.255900,0.313022,1.0,0.25,0.259867,0.284461,97.972973
4,100_025,4,0.466466,0.210450,0.223342,1.0,0.25,0.215988,0.216896,125.945946
...,...,...,...,...,...,...,...,...,...,...
1924,100_025,1924,199.577578,0.167120,0.156760,1.0,0.25,0.188285,0.161940,53885.945946
1925,100_025,1925,199.681181,0.138589,0.127662,1.0,0.25,0.148926,0.133199,53913.918919
1926,100_025,1926,199.785285,0.119407,0.266124,1.0,0.25,0.204188,0.192766,53942.027027
1927,100_025,1927,199.888889,0.113167,0.811016,1.0,0.25,0.436711,0.461756,53970.000000


In [110]:
all_data

,id,bucket,time,acre_rate_primary,acre_rate_secondary,acre_rate_mass_weighted,q,e,seg,acre_rate_mass_weighted_clean,time_days,anio_rel,mes
0,010_000_03,1928,200.022979,-0.003975,-0.011054,0.003852,0.1,0.0,3.0,0.004618,54006.204300,147,12
1,010_000_03,1929,200.101609,-0.003956,-0.011544,0.005504,0.1,0.0,3.0,0.004646,54027.434455,148,1
2,010_000_03,1930,200.204049,-0.003915,-0.011849,0.004429,0.1,0.0,3.0,0.004636,54055.093205,148,2
3,010_000_03,1931,200.313973,-0.003872,-0.011162,0.005433,0.1,0.0,3.0,0.004535,54084.772596,148,3
4,010_000_03,1932,200.408272,-0.003850,-0.010415,0.005710,0.1,0.0,3.0,0.004447,54110.233324,148,4
...,...,...,...,...,...,...,...,...,...,...,...,...,...
143440,100_070_20,19281,1999.556822,-0.002821,-0.005174,0.003443,1.0,0.7,20.0,0.003997,539880.342071,1479,2
143441,100_070_20,19282,1999.661450,-0.002348,-0.004502,0.003936,1.0,0.7,20.0,0.003427,539908.591585,1479,3
143442,100_070_20,19283,1999.763029,-0.001984,-0.005909,0.004781,1.0,0.7,20.0,0.003947,539936.017895,1479,4
143443,100_070_20,19284,1999.881559,-0.001708,-0.010768,0.005459,1.0,0.7,20.0,0.006238,539968.020870,1479,5


In [111]:
df_concat = pd.concat([df_unique, all_data], axis=0, ignore_index=True)


In [112]:
features_df = compute_features(df_concat, n_jobs=-1)


[Parallel(n_jobs=-1)]: Using backend LokyBackend with 10 concurrent workers.
[Parallel(n_jobs=-1)]: Done  30 tasks      | elapsed:    0.6s
[Parallel(n_jobs=-1)]: Done 199 out of 199 | elapsed:    0.7s finished


In [113]:
features_df

,id,DN_HistogramMode_5,DN_HistogramMode_10,CO_f1ecac,CO_FirstMin_ac,CO_HistogramAMI_even_2_5,CO_trev_1_num,MD_hrv_classic_pnn40,SB_BinaryStats_mean_longstretch1,SB_TransitionMatrix_3ac_sumdiagcov,...,FC_LocalSimple_mean1_tauresrat,DN_OutlierInclude_p_001_mdrmd,DN_OutlierInclude_n_001_mdrmd,SP_Summaries_welch_rect_area_5_1,SB_BinaryStats_diff_longstretch0,SB_MotifThree_quantile_hh,SC_FluctAnal_2_rsrangefit_50_1_logi_prop_r1,SC_FluctAnal_2_dfa_50_1_2_logi_prop_r1,SP_Summaries_welch_rect_centroid,FC_LocalSimple_mean3_stderr
0,100_025,-1.284832,1.223345,1.656555,5.0,0.490778,0.475230,0.964212,7.0,0.040340,...,1.000000,0.000000,-0.002592,0.008278,9.0,1.922048,0.122449,0.795918,0.650408,1.158686
1,010_000_03,0.140183,0.475001,0.624150,1.0,0.012918,-0.023771,0.972222,11.0,0.000335,...,1.000000,0.080444,0.000000,0.200731,6.0,2.194171,0.191489,0.851064,1.607612,1.144826
2,010_000_04,0.261723,-0.047082,0.624205,1.0,0.009674,0.487267,0.983516,8.0,0.000487,...,1.000000,-0.017833,-0.004115,0.176287,6.0,2.192833,0.234043,0.148936,1.564660,1.168471
3,010_000_05,-0.127549,0.184444,0.627728,2.0,0.014503,0.389479,0.983425,10.0,0.000121,...,1.000000,-0.089655,0.092414,0.189755,7.0,2.196128,0.404255,0.234043,1.601476,1.162881
4,010_000_06,-0.346514,-0.020251,0.616289,1.0,0.005896,-0.454346,0.973684,9.0,0.000164,...,1.000000,-0.051176,-0.020747,0.178099,6.0,2.195749,0.234043,0.829787,1.632156,1.168218
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
194,100_070_16,-0.022026,-0.953455,1.402958,4.0,0.030549,0.617870,0.952843,12.0,0.004647,...,0.333333,0.160665,-0.129501,0.326483,8.0,2.066426,0.127660,0.872340,0.846757,1.128475
195,100_070_17,-0.260943,-0.563960,1.349294,4.0,0.052848,0.700096,0.958449,7.0,0.009358,...,0.333333,-0.110650,0.015214,0.314337,8.0,2.053895,0.382979,0.191489,0.846757,1.143114
196,100_070_18,-0.305550,-0.581367,1.490160,4.0,0.032162,-0.000657,0.955923,14.0,0.002635,...,0.333333,-0.357634,0.303989,0.349589,8.0,2.075215,0.148936,0.808511,0.846757,1.098622
197,100_070_19,-0.141177,-0.419770,1.380118,4.0,0.037441,0.718192,0.961219,8.0,0.003154,...,0.333333,0.157676,-0.084371,0.341818,9.0,2.071191,0.127660,0.765957,0.846757,1.111819


In [114]:
def standardize_features(df: pd.DataFrame):
    """
    Estandariza (media 0, varianza 1) todas las columnas numéricas
    excepto 'id'.
    """

    feature_cols = df.columns.difference(['id'])   # solo las 22 features
    scaler = StandardScaler()
    scaled = scaler.fit_transform(df[feature_cols])

    df_std = pd.DataFrame(scaled, columns=feature_cols, index=df.index)
    df_std.insert(0, 'id', df['id'])


    return df_std, scaler

In [115]:
df_standardized, fitted_scaler = standardize_features(features_df)


In [116]:
df_std = df_standardized   # o usa df_standardized en memoria
feature_cols = df_std.columns.difference(["id"])          # lista de 22 features

def compute_distances(df: pd.DataFrame, target_id: str) -> pd.DataFrame:

    X = df.loc[df["id"] != target_id, feature_cols].to_numpy()
    x0 = df.loc[df["id"] == target_id, feature_cols].to_numpy()

    euclidean  = cdist(X, x0, metric="euclidean").flatten()
    manhattan  = cdist(X, x0, metric="cityblock").flatten()
    cosine     = cdist(X, x0, metric="cosine").flatten()

    cov        = np.cov(df[feature_cols].to_numpy(), rowvar=False)
    VI         = np.linalg.inv(cov)
    mahalan    = cdist(X, x0, metric="mahalanobis", VI=VI).flatten()

    other_ids = df.loc[df["id"] != target_id, "id"].to_numpy()
    dist_df = pd.DataFrame({
        "id":        other_ids,
        "euclidean":  euclidean,
        "manhattan":  manhattan,
        "cosine":     cosine,
        "mahalanobis": mahalan,
    })

    
    dist_df[['q', 'e', 'seg']] = dist_df['id'].str.split('_', expand=True)

    dist_df['q'] = dist_df['q'].astype(int)/100
    dist_df['e'] = dist_df['e'].astype(int)/100
    dist_df.drop(columns='seg', inplace=True)
    

    return dist_df.sort_values("manhattan").reset_index(drop=True)




In [117]:

df_standardized[['q', 'e', 'seg']] = df_standardized['id'].str.split('_', expand=True)

df_standardized['q'] = df_standardized['q'].astype(int)/100
df_standardized['e'] = df_standardized['e'].astype(int)/100
df_standardized.drop(columns='seg', inplace=True)

In [118]:
df_standardized

,id,CO_Embed2_Dist_tau_d_expfit_meandiff,CO_FirstMin_ac,CO_HistogramAMI_even_2_5,CO_f1ecac,CO_trev_1_num,DN_HistogramMode_10,DN_HistogramMode_5,DN_OutlierInclude_n_001_mdrmd,DN_OutlierInclude_p_001_mdrmd,...,SB_BinaryStats_diff_longstretch0,SB_BinaryStats_mean_longstretch1,SB_MotifThree_quantile_hh,SB_TransitionMatrix_3ac_sumdiagcov,SC_FluctAnal_2_dfa_50_1_2_logi_prop_r1,SC_FluctAnal_2_rsrangefit_50_1_logi_prop_r1,SP_Summaries_welch_rect_area_5_1,SP_Summaries_welch_rect_centroid,q,e
0,100_025,5.735380,1.467125,10.049599,-0.121989,0.930782,3.907392,-3.484900,-0.169705,0.070485,...,2.432146,-0.865217,-3.848577,0.886894,0.872603,-1.238618,-3.101803,-1.020401,1.0,0.25
1,010_000_03,-1.628653,-1.680669,-0.534832,-0.239234,-0.446843,1.795783,0.695456,-0.159563,0.351414,...,-0.403774,-0.415372,1.012256,-0.592745,1.062040,-0.940566,-1.285144,1.680139,0.1,0.00
2,010_000_04,-1.196508,-1.680669,-0.606691,-0.239228,0.964013,0.322614,1.052001,-0.175665,0.008209,...,-0.403774,-0.752756,0.988352,-0.587107,-1.349924,-0.756861,-1.515889,1.558961,0.1,0.00
3,010_000_05,-1.325594,-0.893721,-0.499730,-0.238828,0.694044,0.975915,-0.089950,0.202029,-0.242613,...,0.541533,-0.527833,1.047214,-0.600643,-1.057565,-0.022042,-1.388750,1.662828,0.1,0.00
4,010_000_06,-1.455806,-1.680669,-0.690368,-0.240127,-1.635558,0.398324,-0.732294,-0.240741,-0.108233,...,-0.403774,-0.640294,1.040434,-0.599057,0.988950,-0.756861,-1.498785,1.749383,0.1,0.00
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
194,100_070_16,-0.690742,0.680177,-0.144302,-0.150789,1.324577,-2.234905,0.219606,-0.666270,0.631566,...,1.486839,-0.302911,-1.269609,-0.433260,1.135130,-1.216123,-0.098115,-0.466444,1.0,0.70
195,100_070_17,-0.392968,0.680177,0.349607,-0.156883,1.551584,-1.135864,-0.481269,-0.100033,-0.315933,...,1.486839,-0.865217,-1.493442,-0.259030,-1.203745,-0.113895,-0.212761,-0.466444,1.0,0.70
196,100_070_18,0.571615,0.680177,-0.108579,-0.140886,-0.383030,-1.184982,-0.612126,1.029869,-1.178462,...,1.486839,-0.077988,-1.112603,-0.507665,0.915860,-1.124271,0.119997,-0.466444,1.0,0.70
197,100_070_19,-0.084080,0.680177,0.008334,-0.153383,1.601541,-0.729001,-0.129929,-0.489684,0.621129,...,2.432146,-0.752756,-1.184482,-0.488483,0.769681,-1.216123,0.046642,-0.466444,1.0,0.70


In [119]:

#Columnas clave
id_col      = "id"
target_cols = ["q", "e"] #q,e se trabajan como variables categoricas (porque finalmente son identificadores de cada serie)
feature_cols = df_standardized.columns.difference([id_col] + target_cols)

#Codificar categorías
le_dict = {}
Y_encoded = pd.DataFrame(index=df_standardized.index)
for col in target_cols:
    le = LabelEncoder().fit(df_standardized[col])
    Y_encoded[col] = le.transform(df_standardized[col])
    le_dict[col] = le

X = df_standardized[feature_cols]
Y = Y_encoded[target_cols]

#Definir clasificador multisalida (estoy usando q,e como variabkles obj)
base_clf    = RandomForestClassifier(random_state=42, n_jobs=-1)
multi_clf   = MultiOutputClassifier(base_clf, n_jobs=-1)

#Grid para optimizar hiperparametros 
param_grid = {
    "estimator__n_estimators":     [200, 500], #cantidad de arboles
    "estimator__max_depth":        [None, 20, 40], #profundidad del arbol
    "estimator__min_samples_leaf": [1, 2, 4], 
    "estimator__max_features":     ["sqrt", "log2"]
}

grid = GridSearchCV(
    multi_clf,
    param_grid,
    cv=5,
    scoring="r2",  # multioutput: promedia accuracy de cada salida
    n_jobs=-1
)

# entrenar y extraer el mejor modelo
best_multi = grid.fit(X, Y).best_estimator_

#  Calcular importancias promediadas
#    cada estimador interno tiene feature_importances_
importances_each = np.vstack([
    est.feature_importances_
    for est in best_multi.estimators_
])    # shape = (n_outputs, n_features)

importances = importances_each.mean(axis=0)
importances /= importances.sum()    # normalizar a suma = 1


In [120]:
# Ponderar el vector caracteristicas
df_weighted = df_standardized.copy()
df_weighted[feature_cols] = df_weighted[feature_cols].mul(importances, axis=1)

In [121]:
importances #ninguna feature es significativamente mas importante que el resto

array([0.0639984 , 0.02759477, 0.05368123, 0.12369975, 0.03240221,
       0.02668342, 0.02298802, 0.01907842, 0.02334617, 0.04881785,
       0.05965531, 0.01089031, 0.03230789, 0.02204515, 0.01418137,
       0.01699434, 0.11017849, 0.04360048, 0.01688418, 0.02421831,
       0.06974494, 0.137009  ])

In [122]:
df_weighted

,id,CO_Embed2_Dist_tau_d_expfit_meandiff,CO_FirstMin_ac,CO_HistogramAMI_even_2_5,CO_f1ecac,CO_trev_1_num,DN_HistogramMode_10,DN_HistogramMode_5,DN_OutlierInclude_n_001_mdrmd,DN_OutlierInclude_p_001_mdrmd,...,SB_BinaryStats_diff_longstretch0,SB_BinaryStats_mean_longstretch1,SB_MotifThree_quantile_hh,SB_TransitionMatrix_3ac_sumdiagcov,SC_FluctAnal_2_dfa_50_1_2_logi_prop_r1,SC_FluctAnal_2_rsrangefit_50_1_logi_prop_r1,SP_Summaries_welch_rect_area_5_1,SP_Summaries_welch_rect_centroid,q,e
0,100_025,0.367055,0.040485,0.539475,-0.015090,0.030159,0.104263,-0.080111,-0.003238,0.001646,...,0.034491,-0.014704,-0.424030,0.038669,0.014733,-0.029997,-0.216335,-0.139804,1.0,0.25
1,010_000_03,-0.104231,-0.046378,-0.028710,-0.029593,-0.014479,0.047918,0.015987,-0.003044,0.008204,...,-0.005726,-0.007059,0.111529,-0.025844,0.017932,-0.022779,-0.089632,0.230194,0.1,0.00
2,010_000_04,-0.076575,-0.046378,-0.032568,-0.029592,0.031236,0.008608,0.024183,-0.003351,0.000192,...,-0.005726,-0.012793,0.108895,-0.025598,-0.022792,-0.018330,-0.105726,0.213592,0.1,0.00
3,010_000_05,-0.084836,-0.024662,-0.026826,-0.029543,0.022489,0.026041,-0.002068,0.003854,-0.005664,...,0.007680,-0.008970,0.115380,-0.026188,-0.017856,-0.000534,-0.096858,0.227822,0.1,0.00
4,010_000_06,-0.093169,-0.046378,-0.037060,-0.029704,-0.052996,0.010629,-0.016834,-0.004593,-0.002527,...,-0.005726,-0.010881,0.114633,-0.026119,0.016698,-0.018330,-0.104533,0.239681,0.1,0.00
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
194,100_070_16,-0.044206,0.018769,-0.007746,-0.018653,0.042919,-0.059635,0.005048,-0.012711,0.014745,...,0.021085,-0.005148,-0.139884,-0.018890,0.019166,-0.029452,-0.006843,-0.063907,1.0,0.70
195,100_070_17,-0.025149,0.018769,0.018767,-0.019406,0.050275,-0.030309,-0.011063,-0.001908,-0.007376,...,0.021085,-0.014704,-0.164545,-0.011294,-0.020324,-0.002758,-0.014839,-0.063907,1.0,0.70
196,100_070_18,0.036582,0.018769,-0.005829,-0.017428,-0.012411,-0.031619,-0.014072,0.019648,-0.027513,...,0.021085,-0.001325,-0.122585,-0.022134,0.015464,-0.027228,0.008369,-0.063907,1.0,0.70
197,100_070_19,-0.005381,0.018769,0.000447,-0.018973,0.051893,-0.019452,-0.002987,-0.009342,0.014501,...,0.034491,-0.012793,-0.130504,-0.021298,0.012995,-0.029452,0.003253,-0.063907,1.0,0.70


In [123]:
df_weighted["id"] = df_weighted["id"].replace("100_025", "100_025_00")


In [124]:
#Distancias respecto de target
TARGET = "100_020_10"


In [125]:
distances = compute_distances(df_weighted, TARGET)


In [126]:
metric_cols = ["euclidean", "manhattan", "cosine", "mahalanobis"]
from sklearn.preprocessing import MinMaxScaler

scaler = MinMaxScaler(feature_range=(0, 1))
distances[metric_cols] = scaler.fit_transform(distances[metric_cols])

In [127]:
distances

,id,euclidean,manhattan,cosine,mahalanobis,q,e
0,100_060_07,0.038236,0.000000,0.051399,0.141230,1.0,0.6
1,100_060_04,0.004800,0.007535,0.030195,0.121173,1.0,0.6
2,100_050_05,0.018974,0.024962,0.000000,0.051051,1.0,0.5
3,100_060_12,0.050503,0.037183,0.037984,0.007031,1.0,0.6
4,100_060_11,0.047754,0.043417,0.041596,0.102734,1.0,0.6
...,...,...,...,...,...,...,...
193,100_010_19,0.334411,0.615122,0.265100,0.298630,1.0,0.1
194,100_010_16,0.348985,0.638749,0.366752,0.470229,1.0,0.1
195,100_010_12,0.390570,0.762861,0.320321,0.513339,1.0,0.1
196,100_010_14,0.452891,0.769373,0.319311,0.719842,1.0,0.1


In [128]:
df_median = (
    distances
    .groupby(["q", "e"], as_index=False)[metric_cols]
    .median()
    .sort_values(["manhattan"])
)

In [129]:
df_median

,q,e,euclidean,manhattan,cosine,mahalanobis
9,1.00,0.6,0.083267,0.089571,0.105582,0.157056
8,1.00,0.5,0.080055,0.122938,0.124798,0.192400
10,1.00,0.7,0.110358,0.139485,0.182847,0.201282
7,1.00,0.4,0.203629,0.324484,0.446729,0.226665
6,1.00,0.3,0.239160,0.364324,0.629896,0.206765
5,1.00,0.2,0.251554,0.364723,0.709803,0.199403
0,0.10,0.0,0.388903,0.411925,0.732541,0.192504
1,0.25,0.0,0.378997,0.437117,0.814754,0.158393
4,1.00,0.1,0.268718,0.442003,0.378683,0.313922
2,0.50,0.0,0.356218,0.453401,0.892788,0.173551


In [130]:
def build_id(q, e):
    q_int = int(round(q * 100))  # 1.00 → 100, 0.25 → 25 …
    e_int = int(round(e * 100))  # 0.70 → 70 …
    return f"{q_int:03d}_{e_int:03d}"

df_median["id"] = df_median.apply(lambda r: build_id(r["q"], r["e"]), axis=1)

# (Opcional) Reordenar columnas para que id quede al frente
cols_order = ["id", "q", "e", "euclidean", "manhattan", "cosine", "mahalanobis"]
df_median = df_median[cols_order]


In [131]:
df_median

,id,q,e,euclidean,manhattan,cosine,mahalanobis
9,100_060,1.00,0.6,0.083267,0.089571,0.105582,0.157056
8,100_050,1.00,0.5,0.080055,0.122938,0.124798,0.192400
10,100_070,1.00,0.7,0.110358,0.139485,0.182847,0.201282
7,100_040,1.00,0.4,0.203629,0.324484,0.446729,0.226665
6,100_030,1.00,0.3,0.239160,0.364324,0.629896,0.206765
5,100_020,1.00,0.2,0.251554,0.364723,0.709803,0.199403
0,010_000,0.10,0.0,0.388903,0.411925,0.732541,0.192504
1,025_000,0.25,0.0,0.378997,0.437117,0.814754,0.158393
4,100_010,1.00,0.1,0.268718,0.442003,0.378683,0.313922
2,050_000,0.50,0.0,0.356218,0.453401,0.892788,0.173551


In [132]:
def plot_distance_vs_e_interactive(
    dist_df: pd.DataFrame,
    distance: str = "euclidean",
    *,
    manual_colors: dict | None = None,
    title: str | None = None,
    save_path: str | None = None,
):

    # -------- variable global target ---------------------------------------
    if "TARGET" not in globals():
        raise NameError(
            "Debe existir una variable global llamada 'target' con el id objetivo."
        )
    target_id: str = globals()["TARGET"]

    # -------- comprobar columnas requeridas ---------------------------------
    required_cols = {"id", "q", "e", distance}
    if not required_cols.issubset(dist_df.columns):
        raise ValueError(f"dist_df debe contener las columnas {required_cols}")

    # -------- detectar cómo están q y e (entero o flotante) -----------------
    store_as_float = dist_df["q"].max() <= 10  # heurística: 1.00, 0.25, etc.

    # -------- extraer q_tag y e_tag del target ------------------------------
    try:
        q_tag_t, e_tag_t, _ = target_id.split("_")
        q_tag_t, e_tag_t = int(q_tag_t), int(e_tag_t)
    except Exception:
        raise ValueError("La variable 'target' debe tener formato 'qqq_eee_seg'.")

    # valores de q y e en el mismo formato que dist_df
    q_val = q_tag_t / 100 if store_as_float else q_tag_t
    e_val = e_tag_t / 100 if store_as_float else e_tag_t

    # -------- añadir la fila del objetivo (distance = 0) --------------------
    target_row = {"id": target_id, distance: 0.0, "q": q_val, "e": e_val}
    df_plot = pd.concat([dist_df, pd.DataFrame([target_row])], ignore_index=True)

    # -------- columnas auxiliares para el gráfico ---------------------------
    df_plot["e_float"] = df_plot["e"] if store_as_float else df_plot["e"] / 100.0
    df_plot["q_float"] = df_plot["q"] if store_as_float else df_plot["q"] / 100.0

    # etiqueta combinada q_e siempre con 3 dígitos
    df_plot["q_e"] = (
        (df_plot["q_float"] * 100)
        .round()
        .astype(int)
        .astype(str)
        .str.zfill(3)
        + "_"
        + (df_plot["e_float"] * 100)
        .round()
        .astype(int)
        .astype(str)
        .str.zfill(3)
    )

    # -------- asignar colores ------------------------------------------------
    palette = itertools.cycle(px.colors.qualitative.Plotly)
    color_map = {}
    manual_colors = manual_colors or {}

    for _, row in df_plot.iterrows():
        key = (
            int(round(row["q_float"] * 100)),
            int(round(row["e_float"] * 100)),
        )  # siempre enteros 0-100
        if key not in color_map:
            color_map[key] = manual_colors.get(key, next(palette))

    df_plot["color"] = df_plot.apply(
        lambda r: color_map[
            (int(round(r["q_float"] * 100)), int(round(r["e_float"] * 100)))
        ],
        axis=1,
    )

    color_discrete_map = {
        f"{q:03d}_{e:03d}": col for (q, e), col in color_map.items()
    }

    # -------- scatter interactivo -------------------------------------------
    fig = px.scatter(
        df_plot[df_plot["id"] != target_id],
        x="e_float",
        y=distance,
        color="q_e",
        color_discrete_map=color_discrete_map,
        hover_data={
            "id": True,
            "q_float": ":.2f",
            "e_float": ":.2f",
            distance: ":.4f",
            "q_e": False,
        },
        labels={
            "e_float": "e (excentricidad)",
            distance: f"Distancia {distance}",
        },
        title=title or f"{distance.capitalize()} vs e — objetivo {target_id}",
        template="plotly_white",
    )

    # -------- punto objetivo -------------------------------------------------
    fig.add_trace(
        go.Scatter(
            x=[df_plot.loc[df_plot["id"] == target_id, "e_float"].iloc[0]],
            y=[0],
            mode="markers",
            marker=dict(
                size=14, symbol="star", color="black", line=dict(width=1, color="white")
            ),
            name=f"Objetivo {target_id}",
            hovertemplate=(
                f"<b>Objetivo</b><br>id: {target_id}<br>"
                f"q: {q_val:.2f}<br>e: {e_val:.2f}<br>{distance}: 0"
            ),
            showlegend=True,
        )
    )

    if save_path:
        if Path(save_path).suffix.lower() == ".html":
            fig.write_html(save_path)
        else:  # requiere `pip install kaleido`
            fig.write_image(save_path, engine="kaleido", scale=2)
        print(f"✅ Figura guardada en {save_path}")

    #fig.show()
    return fig

In [133]:
manual  = {}

plot_distance_vs_e_interactive(
    df_median,
    distance="manhattan",
    manual_colors=manual,
    title="Manhattan vs e"
)

In [134]:
manual  = {}

plot_distance_vs_e_interactive(
    distances,
    distance="manhattan",
    manual_colors=manual,
    title="Manhattan vs e"
)